## Correlação entre as variáveis ao longo do tempo

Implementando um gráfico animado para visualizar a correlação entre as variáveis ao longo do tempo.

In [1]:
import pandas as pd 
import numpy as np 
import matplotlib.pyplot as plt 
from matplotlib.animation import FuncAnimation
from IPython.display import HTML
import seaborn as sns 
from scipy.stats import norm
import datetime as dt
from tqdm import tqdm
from yahooquery import Ticker


import warnings
warnings.filterwarnings('ignore')

## Baixando os dados 

In [2]:
# Ticker selecionados para compor a carteira
tickers = ['^BVSP', '^IXIC', '^GSPC', '^FTSE', '^GDAXI', '^HSI', '^N225']

In [3]:
# Baixando os dados do TICKERs 

# Baixando os dados do Yahoo Finance

# datas de início e fim
start_date = '2006-01-01'
end_date = '2026-01-01'

# Convertendo as datas para o formato datetime
start_date = dt.datetime.strptime(start_date, '%Y-%m-%d')
end_date = dt.datetime.strptime(end_date, '%Y-%m-%d')

tickers_obj = Ticker(tickers)
df= tickers_obj.history(start= start_date, end= end_date, interval='1d')['close']

# Visualizando os dados
df.head()

symbol  date      
^BVSP   2006-01-02    33507.0
        2006-01-03    34541.0
        2006-01-04    35002.0
        2006-01-05    34936.0
        2006-01-06    35475.0
Name: close, dtype: float64

In [4]:
# Resetando o indice para facilidar a manipulação
df = df.reset_index()

# Pivotando o dataframe para que as colunas virem os tickers
df = df.pivot(index='date', columns='symbol', values='close')

# Renomeando o indice para 'Data'
df.index.name = 'Data'

# Excluindo os dados faltantes
df.dropna(axis = 0, inplace=True)

# Visualizando os dados
df.tail()

symbol,^BVSP,^FTSE,^GDAXI,^GSPC,^HSI,^IXIC,^N225
Data,,,,,,,
2025-12-19,158473.0,9897.400391,24288.400391,6834.500000,25690.529297,23307.619141,49507.210938
2025-12-22,158142.0,9866.000000,24283.970703,6878.490234,25801.769531,23428.830078,50402.390625
2025-12-23,160456.0,9889.200195,24340.060547,6909.790039,25774.140625,23561.839844,50412.871094
2025-12-29,160490.0,9866.500000,24351.119141,6905.740234,25635.230469,23474.349609,50526.921875
2025-12-30,161125.0,9940.700195,24490.410156,6896.240234,25854.599609,23419.080078,50339.480469


## Cálculo da correlação ao longo do tempo

In [5]:
# Parâmetros
cols = tickers
window = 252
step = 20

corrs = np.array([df[cols].iloc[i-window:i].corr().values for i in range(window, len(df), step)]) # cálculo das correlações em janelas móveis
dates = [df.index[i].strftime('%Y-%m-%d') for i in range(window, len(df), step)] # datas das janelas móveis

# DataFrame de correlações
n = len(cols)
pairs = [(cols[r], cols[c]) for r in range(n) for c in range(n) if r < c] # combinações em pares dos ativos

df_corr = pd.DataFrame(
    [[corrs[i][r, c] for r in range(n) for c in range(n) if r < c]
     for i in range(len(corrs))]
)
df_corr.columns = [f"{a}__{b}" for a, b in pairs]
df_corr.index = pd.to_datetime(dates)
df_corr["mean_corr"] = df_corr.mean(axis=1)

In [6]:
# Períodos de destaque
# Crise de 2008
recession_start = pd.Timestamp("2007-12-01")
recession_end = pd.Timestamp("2009-01-06")

# COVID-19
pandemic_start = pd.Timestamp("2020-02-01")
pandemic_end   = pd.Timestamp("2021-06-30")

# Últimos 60 dias
recent_end     = df_corr.index.max()
recent_start   = recent_end - pd.DateOffset(days=60)

# Animação 
fig, (ax_heat, ax_line) = plt.subplots(
    2, 1, figsize=(16, 7),
    gridspec_kw={"height_ratios": [1.5, 1], "hspace": 0.4}
)

def update(i):
    ax_heat.clear()
    ax_line.clear()

    #  Heatmap
    sns.heatmap(
        corrs[i], annot=True, fmt=".2f", cmap="RdBu_r",
        vmin=-1, vmax=1,
        xticklabels=cols, yticklabels=cols,
        ax=ax_heat, cbar=False,
    )
    ax_heat.set_title(f"Correlation: {dates[i]}", fontsize=12)

    # Line chart - Segundo gráfico
    ax_line.plot(df_corr.index, df_corr["mean_corr"],
                 color="#6366f1", linewidth=1.8, alpha=0.9, zorder=3)
    ax_line.axhline(0, color="gray", linewidth=0.8, linestyle="--", zorder=1)

    # Faixa — Crise 2008
    ax_line.axvspan(recession_start, recession_end,
                    color="#ef4444", alpha=0.12, zorder=1, label="2008 Crisis")
    ax_line.axvline(recession_start, color="#ef4444", linewidth=1, linestyle="--", alpha=0.6)
    ax_line.axvline(recession_end,   color="#ef4444", linewidth=1, linestyle="--", alpha=0.6)
    ax_line.text(
        recession_start + (recession_end - recession_start) / 2,
        0.1,
        "2008 Financial Crisis", ha="center", va="bottom",
        fontsize=8, color="#ef4444", fontweight="bold", zorder=4,
    )


    # Faixa — Pandemia
    ax_line.axvspan(pandemic_start, pandemic_end,
                    color="#ef4444", alpha=0.12, zorder=1, label="Pandemic")
    ax_line.axvline(pandemic_start, color="#ef4444", linewidth=1, linestyle="--", alpha=0.6)
    ax_line.axvline(pandemic_end,   color="#ef4444", linewidth=1, linestyle="--", alpha=0.6)
    ax_line.text(
        pandemic_start + (pandemic_end - pandemic_start) / 2,
        0.1,
        "COVID-19", ha="center", va="bottom",
        fontsize=8, color="#ef4444", fontweight="bold", zorder=4,
    )

    # Faixa — Últimos 60 dias
    ax_line.axvspan(recent_start, recent_end,
                    color="#f59e0b", alpha=0.15, zorder=1, label="Last 60 days")
    ax_line.axvline(recent_start, color="#f59e0b", linewidth=1, linestyle="--", alpha=0.7)
    ax_line.text(
        recent_start + (recent_end - recent_start) / 2,
        0.1,
        "Last 60 days", ha="center", va="bottom",
        fontsize=8, color="#f59e0b", fontweight="bold", zorder=4,
    )

    # Ponto e linha do frame atual
    ax_line.scatter(df_corr.index[i], df_corr["mean_corr"].iloc[i],
                    color="#ef4444", zorder=5, s=60)
    ax_line.axvline(df_corr.index[i], color="#ef4444", linewidth=1, linestyle=":", zorder=2)

    ax_line.set_title("Average Correlation Over Time", fontsize=12)
    ax_line.set_ylabel("Average Correlation")
    ax_line.tick_params(axis="x", rotation=45)
    plt.tight_layout()

anim = FuncAnimation(fig, update, frames=len(corrs), interval=400)
html = anim.to_jshtml()

# Save the GIF
#from matplotlib.animation import PillowWriter
#anim.save("correlacao2.gif", writer=PillowWriter(fps=2))

plt.close()
HTML(html)

Animation size has reached 20973485 bytes, exceeding the limit of 20971520.0. If you're sure you want a larger animation embedded, set the animation.embed_limit rc parameter to a larger value (in MB). This and further frames will be dropped.
